# Usage | 4. Data imports for prioritizing gaps
This notebook explains how custom data sets can be imported into FixBikeNet to reprioritize gaps, adapting to a local situation and identifying gaps more realistically.

**Parameters covered**: `import_files['point_data']`

We start every Usage notebook with the standard way of importing FixBikeNet:

In [69]:
import fixbikenet as fbn

## Re-prioritizing growth with point data

Here we work with Copenhagen, Denmark. By default FixBikeNet identifies gaps using betweenness centrality, which is a proxy for expected flow of cyclists in the city. However, the city might have access to additional data sets that can inform the priority of some gaps. For example, in Copenhagen, there is point data available from a (non-representative) citizen survey where citizens reported where they want more or wider bicycle lanes. It could be the city's goal to prioritize bicycle network development in such places. This is possible by loading the survey data via the `import_files['point_data']` parameter. 

First, let's import Copenhagen's bike network and survey data and plot them together:

In [65]:
fbn.settings.import_path = '../../tests/test_data/'
import geopandas as gpd
import osmnx as ox
import folium

# Import bike network
bike_edges = gpd.read_file(fbn.settings.import_path+"copenhagen_bike_network.gpkg", layer="edges")

# Import survey
survey = gpd.read_file(fbn.settings.import_path+"copenhagen_citizen_input.geojson")

# Plot both
viz = survey.explore(
    location=(55.676098, 12.568337),
    zoom_start=13,
    tiles="https://tiles.stadiamaps.com/tiles/alidade_smooth/{z}/{x}/{y}{r}.png", 
    attr="(C) Stadia Maps (C) OpenMapTiles (C) OpenStreetMap contributors",
    style_kwds={"color": "#ff0000", "opacity": 0.2, "fillColor": "#ff0000"},
    name="Survey feedback",
    tooltip = False,
)
viz = bike_edges.explore(
    m=viz, 
    style_kwds={"weight": 2, "color": "#9999cc"},
    name="Existing bike network",
)

folium.LayerControl().add_to(viz)
viz

<div class="admonition caution">
<div class="title">Caution</div>
<p>This data is not representative, but biased by self-selection bias: People self-selected to participate in this survey. Therefore, it is not representative and should not be used for any practical design decisions. However, it works well as a demonstration of FixBikeNet's capabilities.</p>
</div>

Now we are going to compare Copenhagen's top 20 identified gaps without and with this data set, working with local data imports, to demonstrate the re-prioritization feature.

In [66]:
gaps_ordered = fbn.fixbikenet(
    "Copenhagen municipality",
    num_gaps = 20,
    import_files = {
        'city_boundary': 'copenhagen_boundary.geojson',
    },
)

RUNNING FIXBIKENET FOR CITY: Copenhagen municipality
-----------------------------------------------╮


Exporting data          : 100%|████████████████| 1/1 [00:00<00:00,  1.34file/s]

-----------------------------------------------╯
Data exported to ./results/
-----------------------------------------------
FINISHED IN 0:10:27


In [67]:
gaps_ordered_with_survey = fbn.fixbikenet(
    "Copenhagen municipality",
    num_gaps = 20,
    import_files = {
        'city_boundary': 'copenhagen_boundary.geojson',
        'point_data': 'copenhagen_citizen_input.geojson',
    },
)

RUNNING FIXBIKENET FOR CITY: Copenhagen municipality
-----------------------------------------------╮


Exporting data          : 100%|████████████████| 1/1 [00:00<00:00,  1.27file/s]


-----------------------------------------------╯
Data exported to ./results/
-----------------------------------------------
FINISHED IN 0:10:47


In [71]:
import folium

viz = gaps_ordered_with_survey.explore(
    location=(55.676098, 12.568337),
    zoom_start=13,
    tiles="https://tiles.stadiamaps.com/tiles/alidade_smooth/{z}/{x}/{y}{r}.png", 
    attr="(C) Stadia Maps (C) OpenMapTiles (C) OpenStreetMap contributors",
    style_kwds={"weight": 10, "color": "#096a51"},
    name="Identified gaps, re-prioritized by survey",
)
viz = gaps_ordered.explore(
    m=viz, 
    style_kwds={"weight": 4, "color": "#77be3a"},
    name="Identified gaps",
)
viz = survey.explore(
    m=viz,
    style_kwds={"color": "#ff0000", "opacity": 0.2, "fillColor": "#ff0000"},
    name="Survey feedback",
    tooltip = False,
)
viz = bike_edges.explore(
    m=viz,
    style_kwds={"weight": 2, "color": "#9999cc"},
    name="Existing bike network",
    tooltip = False,
)
folium.LayerControl().add_to(viz)
viz

Above we are plotting bike network, survey data, and the top 20 identified gaps without reprioritization (light green) and with reprioritization (dark green). The survey data influences several of the gaps, which now cover streets with more survey points such as Enghavevej/Kingosgade west of the city center, or Stengade instead of Gartnergade north of the city center.